# 05 — Translation Projection

Project actual translation outputs into embedding space to see how they cluster to assess patterns in translations across languages and services and prompt framings.

The scripted comparison layer measures whether usable service outputs show exact convergence, near-form convergence, substantive variation, or insufficient evidence for comparison. Wikipedia presence, source retention, script disagreement, and rationale signals remain separate evidence rather than being folded into causal categories.

**This notebook** asks: *when models produce translation outputs, do those outputs cluster into recognizable types whether by script, by length, by Wikipedia coverage, by agreement?* Translations are the thing the model is actually being asked to commit to, so disagreements in translation space are disagreements about the answer itself rather than about the story told afterward.

Six analyses:

1. **Global translation landscape** (§6.3) — every (language × service) best-candidate translation, colored by script, family, service, and Wikipedia presence.
2. **Per-language scatter** (§6.4) — for each language, embed all eight LLM outputs and measure how tightly they cluster. Tight = consensus. Loose = the transmogrification/productive-disagreement zone.
3. **Service fingerprints** (§6.5) — how does each service span the translation space? Do local models (Llama, Gemma, Qwen, Mistral) show wider distributions than API services?
4. **Cross-service distance matrix** (§6.6) — for each pair of services, mean pairwise distance between their outputs across all languages.
5. **Language family cluster analysis** (§6.7) — do languages from the same family cluster together in embedding space? HDBSCAN cluster purity measured against linguistic family labels.
6. **Consensus language clusters** (§6.8) — each non-consensus language is connected to its nearest exact convergence hub in embedding space, treating translation similarity as a proxy for consensus-language influence.

The analytical move is simple: translation outputs are shorter and more concrete than rationales, so the multilingual encoder will organize them by the surface properties that matter most: script, length, borrowing patterns. These surface properties should track your existing classification categories if the categories are real.
**Exclusion tier: Tier 2 — Translation Analysis** (see [docs/exclusion_strategy.md](../docs/exclusion_strategy.md))

Term-error flags (`has_mixed_script`, `has_placeholder_term`, `has_repetition_loop`, `has_extreme_term_length`, `has_unicode_escape`) and manual `exclude_translation=True` entries drop individual (language × service) rows before embedding. `has_source_term`, `has_script_disagreement`, and `has_any_mixing` are retained as annotation columns for coloring and analysis.


## 5.1 Setup & Data Load

In [1]:
import os
import sys
import warnings
from pathlib import Path

import numpy as np
import pandas as pd
import altair as alt

warnings.filterwarnings('ignore')
alt.data_transformers.disable_max_rows()

sys.path.insert(0, str(Path('..').resolve()))
from scripts.utils import (
    get_data_directory_path, read_csv_file, get_language_family, save_chart,
    detect_dominant_script,
)

DATA_DIR  = get_data_directory_path()
TERM      = 'Digital Humanities'
TERM_SLUG = TERM.lower().replace(' ', '_')
EVAL_DIR  = os.path.join(DATA_DIR, 'translated_terms', TERM_SLUG, 'evaluation')

CACHE_DIR = Path('./eda_cache')
CACHE_DIR.mkdir(exist_ok=True)
FIGURE_DIR = Path('..') / 'figures' / 'dhq_article'
FIGURE_DIR.mkdir(parents=True, exist_ok=True)

LLM_SERVICES = ['claude', 'openai', 'gemini', 'deepseek', 'llama', 'gemma', 'qwen', 'mistral']
ALL_VARIANTS = ['minimal', 'fluent_speaker', 'github_searcher', 'judge']
EMBED_MODEL  = 'paraphrase-multilingual-MiniLM-L12-v2'

print(f'DATA_DIR:  {DATA_DIR}')
print(f'EVAL_DIR:  {EVAL_DIR}')
print(f'Cache:     {CACHE_DIR.resolve()}')

Retrieving translation pipeline data directory path...

DATA_DIR:  /Users/zleblanc/CodingDH/translation_transmogrification_pipeline/datasets
EVAL_DIR:  /Users/zleblanc/CodingDH/translation_transmogrification_pipeline/datasets/translated_terms/digital_humanities/evaluation
Cache:     /Users/zleblanc/CodingDH/translation_transmogrification_pipeline/notebooks/eda_cache


In [2]:
# Load the across_variant_detail CSV — same data file 04 reads from. This gives us one row per (language × service) with a best_candidate translation already resolved across prompt variants.
detail_path = os.path.join(EVAL_DIR, 'across_variant_detail.csv')
detail_df = read_csv_file(detail_path)

# Keep only rows where there is actually a translation to embed
trans_df = detail_df[detail_df['best_candidate'].notna()].copy()
trans_df['best_candidate'] = trans_df['best_candidate'].astype(str).str.strip()
trans_df = trans_df[trans_df['best_candidate'].str.len() > 0].reset_index(drop=True)

# Enrich with features we'll want for coloring
trans_df['script'] = trans_df['best_candidate'].apply(detect_dominant_script)
trans_df['trans_len'] = trans_df['best_candidate'].str.len()

# Wikipedia presence per language (from the Wikipedia service rows in the same CSV)
wiki_langs = set(
    detail_df[
        (detail_df['service'] == 'Wikipedia') &
        (detail_df['best_candidate'].notna()) &
        (detail_df['best_candidate'].astype(str).str.strip() != '')
    ]['language_code']
)
trans_df['has_wikipedia'] = trans_df['language_code'].isin(wiki_langs)

print(f'Total translation rows: {len(trans_df):,}')
print(f'Unique languages:       {trans_df["language_code"].nunique()}')
print(f'Languages with Wikipedia: {len(wiki_langs)}')
print(f'Services: {sorted(trans_df["service"].unique())}')

# ── Language count sanity check (pre-exclusion) ─────────────────────────────
_n = detail_df['language_code'].nunique()
print(f'\nLanguages loaded (pre-exclusion): {_n} (expected 881)')
if _n != 881:
    print(f'  ⚠ Expected 881 — re-run the translation pipeline or check for missing/duplicate language_code rows.')
else:
    print(f'  ✓ Count matches expected 881.')

Total translation rows: 7,539
Unique languages:       881
Languages with Wikipedia: 40
Services: ['Claude', 'DeepSeek', 'EasyNMT', 'Gemini', 'Gemma', 'Google Translate', 'Lingvanex', 'Llama', 'Mistral', 'OpenAI', 'Qwen', 'Wikipedia']

Languages loaded (pre-exclusion): 881 (expected 881)
  ✓ Count matches expected 881.


In [3]:
# ── Tier 2 exclusions ───────────────────────────────────────────────────────
EXCL_PATH  = os.path.join(EVAL_DIR, 'manual_exclusions.csv')
FLAGS_PATH = os.path.join(EVAL_DIR, 'automated_review_signals.csv')

quality_flags_df = read_csv_file(FLAGS_PATH)

TERM_ERROR_COLS = {
    'has_mixed_script':        'mixed_script_services',
    'has_placeholder_term':    'placeholder_term_services',
    'has_repetition_loop':     'repetition_loop_services',
    'has_extreme_term_length': 'extreme_term_length_services',
    'has_unicode_escape':      'unicode_escape_services',
}

# Build per-(language, service) drop set from term-error flags
term_error_pairs = set()
for flag_col, svc_col in TERM_ERROR_COLS.items():
    for _, row in quality_flags_df[quality_flags_df[flag_col] == True].iterrows():
        for svc in str(row.get(svc_col, '')).split(';'):
            svc = svc.strip()
            if svc and svc != 'nan':
                term_error_pairs.add((row['language_code'], svc))

# Manual exclude_translation=True
manual_drop_pairs = set()
if os.path.exists(EXCL_PATH):
    excl_df = read_csv_file(EXCL_PATH)
    whole = excl_df[excl_df['exclude_translation'] == True][['language_code', 'service']]
    manual_drop_pairs = set(zip(whole['language_code'], whole['service']))

all_drop_pairs = term_error_pairs | manual_drop_pairs

# Annotation flags to retain on trans_df
ANNOT_COLS = ['language_code', 'has_source_term', 'has_script_disagreement',
              'has_any_mixing', 'has_romanization', 'quality_flags', 'flag_count']
trans_df = trans_df.merge(quality_flags_df[ANNOT_COLS], on='language_code', how='left')

n_before = len(trans_df)
trans_df = trans_df[
    ~trans_df.apply(lambda r: (r['language_code'], r['service']) in all_drop_pairs, axis=1)
].copy().reset_index(drop=True)
n_after = len(trans_df)
print(f'Tier 2: {n_before - n_after} rows dropped ({n_before} → {n_after} translations)')
print(f'  term-error flags: {len(term_error_pairs)} pairs')
print(f'  manual drops    : {len(manual_drop_pairs)} pairs')


Tier 2: 185 rows dropped (7539 → 7354 translations)
  term-error flags: 185 pairs
  manual drops    : 96 pairs


In [4]:
# Quick look at the data we're about to embed
print('By service:')
print(trans_df.groupby('service').size().sort_values(ascending=False))
print('\nBy script (top 10):')
print(trans_df['script'].value_counts().head(10))
print('\nTranslation length distribution:')
print(trans_df['trans_len'].describe().round(1))

By service:
service
Claude              876
DeepSeek            875
OpenAI              869
Gemini              863
Mistral             859
Llama               852
Qwen                841
Gemma               831
Google Translate    242
Lingvanex           109
EasyNMT              97
Wikipedia            40
dtype: int64

By script (top 10):
script
Latin         5174
Cyrillic       479
Devanagari     399
Arabic         362
CJK            140
Other          104
Bengali         63
Myanmar         51
Japanese        44
Syriac          42
Name: count, dtype: int64

Translation length distribution:
count    7354.0
mean       20.3
std         7.2
min         1.0
25%        16.0
50%        19.0
75%        23.0
max        93.0
Name: trans_len, dtype: float64


## 5.2 Embed Translations

One embedding per translation string. These are generally short, so embedding is fast. We cache to disk so a kernel restart doesn't recompute.

Using the same multilingual model as the rationale notebook (`paraphrase-multilingual-MiniLM-L12-v2`). Scripts differ across languages––Latin, Cyrillic, Arabic, CJK, Devanagari––so a multilingual encoder is essential. The encoder will organize outputs partly by script, which is a feature, not a bug: it lets us see script structure as a check on the embedding's behavior.

In [5]:
from sentence_transformers import SentenceTransformer

model = SentenceTransformer(EMBED_MODEL)
print(f'Model loaded: {EMBED_MODEL}, dim={model.get_sentence_embedding_dimension()}')

Model loaded: paraphrase-multilingual-MiniLM-L12-v2, dim=384


In [6]:
def embed_with_cache(texts, cache_name, batch_size=128):
    '''Embed a list of strings, caching to disk keyed by cache_name.'''
    cache_path = CACHE_DIR / f'{cache_name}.npy'
    if cache_path.exists():
        cached = np.load(cache_path)
        if len(cached) == len(texts):
            print(f'Loading cached embeddings: {cache_path.name}')
            return cached
        print(f'Cache size mismatch ({len(cached)} vs {len(texts)}) — re-embedding.')
        cache_path.unlink()
    print(f'Encoding {len(texts):,} texts → {cache_path.name}')
    vecs = model.encode(
        texts,
        batch_size=batch_size,
        show_progress_bar=True,
        convert_to_numpy=True,
        normalize_embeddings=True,
    )
    np.save(cache_path, vecs)
    return vecs

trans_vecs = embed_with_cache(trans_df['best_candidate'].tolist(), 'translation_vecs')
print(f'Translation embeddings: {trans_vecs.shape}')

Encoding 7,354 texts → translation_vecs.npy


Batches:   0%|          | 0/58 [00:00<?, ?it/s]

Translation embeddings: (7354, 384)


## 5.3 Global Translation Landscape — UMAP with four colorings

Project everything into 2D once, then color four ways to see what organizes the space.

Expected: script type will dominate the global structure (writing systems are a strong visual feature of short strings). Wikipedia/no-Wikipedia should show up as a density difference rather than a clean split — the Wikipedia languages are a small minority (40 of 880) distributed across scripts.

In [7]:
import umap
import hdbscan

# One UMAP for the whole landscape; reused across all four colorings
reducer = umap.UMAP(
    n_neighbors=15,
    min_dist=0.1,
    n_components=2,
    metric='cosine',
    random_state=42,
)
coords = reducer.fit_transform(trans_vecs)
trans_df['umap_x'] = coords[:, 0]
trans_df['umap_y'] = coords[:, 1]
print('Projection complete.')

Projection complete.


In [8]:
# Four-panel plot: same coords, four color mappings
ax = dict(
    x=alt.X('umap_x:Q', title='UMAP-1', axis=alt.Axis(labels=False, ticks=False)),
    y=alt.Y('umap_y:Q', title='UMAP-2', axis=alt.Axis(labels=False, ticks=False)),
)
base = alt.Chart(trans_df).mark_circle(size=20, opacity=0.55)
tooltip = ['language_name:N', 'service:N', 'best_candidate:N', 'script:N']

# Keep only the most populated scripts in the legend; collapse the rest
top_scripts = trans_df['script'].value_counts().head(8).index.tolist()
trans_df['script_plot'] = trans_df['script'].where(trans_df['script'].isin(top_scripts), 'Other')
trans_df['wikipedia_label'] = np.where(trans_df['has_wikipedia'], 'Wikipedia term', 'No Wikipedia term')

script_plot = (
    alt.Chart(trans_df).mark_circle(size=20, opacity=0.55)
    .encode(**ax, color=alt.Color('script_plot:N', title='Script',
                                   scale=alt.Scale(scheme='tableau10')),
            tooltip=tooltip)
    .properties(width=340, height=340, title='Colored by dominant script')
)

service_plot = base.encode(
    **ax,
    color=alt.Color('service:N', scale=alt.Scale(scheme='category10'), title='Service'),
    tooltip=tooltip,
).properties(width=340, height=340, title='Colored by service')

wiki_plot = base.encode(
    **ax,
    color=alt.Color('wikipedia_label:N',
                    scale=alt.Scale(domain=['Wikipedia term', 'No Wikipedia term'], range=['#e45756', '#a9a9a9']),
                    title='Wikipedia evidence'),
    tooltip=tooltip,
).properties(width=340, height=340, title='Colored by Wikipedia presence')

family_plot = base.encode(
    **ax,
    color=alt.Color('language_family:N', title='Language Family'),
    tooltip=tooltip,
).properties(width=340, height=340, title='Colored by language family')

global_translation_landscape_chart = alt.hconcat(script_plot, service_plot, wiki_plot).resolve_scale(color='independent')
display(global_translation_landscape_chart)
save_chart(global_translation_landscape_chart, FIGURE_DIR / 'global_translation_embedding_landscape.png')

alt.HConcatChart(...)

In [9]:
family_plot

alt.Chart(...)

## 5.4 Per-Language Scatter — are the services converging or diverging?

For each language, I take the available LLM outputs and measure how tightly they cluster in embedding space. This provides a continuous complement to exact string comparison: non-identical strings may still occupy nearby regions of the multilingual embedding space.

I compute **mean pairwise cosine distance** among the LLM outputs per language. Lower values indicate tighter geometric clustering and higher values indicate greater dispersion. This is a diagnostic measurement, not a judgment about correctness or fabrication.

In [10]:
from scipy.spatial.distance import pdist

# Per-language: gather the LLM outputs and compute pairwise distance
llm_rows = trans_df[trans_df['service'].str.lower().isin(LLM_SERVICES)].copy()

scatter_rows = []
for (lang, term_src), g in llm_rows.groupby(['language_code', 'term_source']):
    if len(g) < 2:
        continue
    idxs = g.index.tolist()
    vecs = trans_vecs[idxs]
    # Mean pairwise cosine distance
    pairwise = pdist(vecs, metric='cosine')
    scatter_rows.append({
        'language_code': lang,
        'language_name': g['language_name'].iloc[0],
        'language_family': g['language_family'].iloc[0],
        'has_wikipedia': g['has_wikipedia'].iloc[0],
        'n_services': len(g),
        'mean_pairwise_distance': float(pairwise.mean()),
        'max_pairwise_distance': float(pairwise.max()),
    })

scatter_df = pd.DataFrame(scatter_rows)
projection_metrics_path = os.path.join(EVAL_DIR, 'translation_projection_language_metrics.csv')
scatter_df.to_csv(projection_metrics_path, index=False)
print(f'Saved per-language projection metrics: {projection_metrics_path}')
print(f'Languages with ≥2 LLM translations: {len(scatter_df):,}')
print(f'\nMean pairwise distance by Wikipedia presence:')
print(scatter_df.groupby('has_wikipedia')['mean_pairwise_distance']
        .agg(['mean', 'median', 'std', 'count']).round(3))

Saved per-language projection metrics: /Users/zleblanc/CodingDH/translation_transmogrification_pipeline/datasets/translated_terms/digital_humanities/evaluation/translation_projection_language_metrics.csv
Languages with ≥2 LLM translations: 881

Mean pairwise distance by Wikipedia presence:
                mean  median    std  count
has_wikipedia                             
False          0.392   0.423  0.145    841
True           0.158   0.152  0.115     40


In [11]:
# Histogram: distribution of mean pairwise distance, split by Wikipedia
scatter_df['wikipedia_label'] = np.where(scatter_df['has_wikipedia'], 'Wikipedia term', 'No Wikipedia term')
wikipedia_consensus_chart = alt.Chart(scatter_df).mark_bar(opacity=0.7).encode(
    x=alt.X('mean_pairwise_distance:Q', bin=alt.Bin(maxbins=40),
            title='Mean pairwise cosine distance among LLM outputs'),
    y=alt.Y('count():Q', title='Number of languages'),
    color=alt.Color('wikipedia_label:N',
                    scale=alt.Scale(domain=['Wikipedia term', 'No Wikipedia term'], range=['#e45756', '#a9a9a9']),
                    title='Wikipedia evidence'),
    tooltip=['wikipedia_label:N', 'count():Q'],
).properties(
    width=640, height=320,
    title='Translation consensus by Wikipedia presence (lower = more consensus)',
)
display(wikipedia_consensus_chart)
save_chart(wikipedia_consensus_chart, FIGURE_DIR / 'translation_consensus_by_wikipedia_presence.png')

alt.Chart(...)

In [12]:
# These extremes identify candidates for close reading; embedding distance alone does not explain why they cluster or diverge.
print('Most CONSENSUAL (tightest service cluster):')
print(scatter_df.nsmallest(15, 'mean_pairwise_distance')[
    ['language_name', 'language_family', 'has_wikipedia', 'mean_pairwise_distance']
].to_string(index=False))

print('\nMost DIVERGENT (loosest service cluster):')
print(scatter_df.nlargest(15, 'mean_pairwise_distance')[
    ['language_name', 'language_family', 'has_wikipedia', 'mean_pairwise_distance']
].to_string(index=False))

Most CONSENSUAL (tightest service cluster):
       language_name         language_family  has_wikipedia  mean_pairwise_distance
  Catalan; Valencian Indo-European languages           True            0.000000e+00
          Portuguese Indo-European languages           True            0.000000e+00
  Spanish; Castilian Indo-European languages           True            2.220446e-16
              Korean        Language isolate           True            4.720034e-14
               Latin Indo-European languages           True            2.513856e-03
              Bihari Indo-European languages          False            5.583761e-03
             Swedish Indo-European languages           True            1.399507e-02
              Syriac  Afro-Asiatic languages          False            1.758950e-02
            Corsican Indo-European languages          False            2.055671e-02
         Interlingua    Artificial languages          False            2.375391e-02
            Cherokee            

## 5.5 Service Fingerprints — do local models show wider distributions?

For each service, what is the spread of its translation outputs in embedding space? A service with a tight distribution is producing a narrow range of outputs (possibly because it defaults to a narrow translation strategy — e.g., always loanword). A service with a wide distribution is either doing more varied translation work (ideal) or hallucinating more varied outputs (problematic). To be clear, you can't tell from the distribution alone, but the width itself is visible.

In [13]:
# Per service: distance from service's own centroid
service_rows = []
for svc, g in llm_rows.groupby('service'):
    idxs = g.index.tolist()
    vecs = trans_vecs[idxs]
    centroid = vecs.mean(axis=0, keepdims=True)
    from scipy.spatial.distance import cdist
    dists = cdist(vecs, centroid, metric='cosine').flatten()
    for d in dists:
        service_rows.append({'service': svc, 'dist_from_centroid': float(d)})

service_spread_df = pd.DataFrame(service_rows)
print('Spread from service centroid (higher = wider output distribution):')
print(service_spread_df.groupby('service')['dist_from_centroid']
        .agg(['mean', 'median', 'std']).round(3))

Spread from service centroid (higher = wider output distribution):
           mean  median    std
service                       
Claude    0.284   0.217  0.146
DeepSeek  0.288   0.246  0.128
Gemini    0.271   0.200  0.152
Gemma     0.307   0.299  0.082
Llama     0.318   0.301  0.090
Mistral   0.304   0.283  0.146
OpenAI    0.225   0.116  0.179
Qwen      0.310   0.290  0.117


In [14]:
service_spread_chart = alt.Chart(service_spread_df).mark_boxplot(extent='min-max').encode(
    x=alt.X('service:N', title=None),
    y=alt.Y('dist_from_centroid:Q', title='Distance from service centroid'),
    color=alt.Color('service:N', legend=None, scale=alt.Scale(scheme='category10')),
).properties(
    width=400, height=320,
    title='Translation output spread by service',
)
display(service_spread_chart)
save_chart(service_spread_chart, FIGURE_DIR / 'translation_output_spread_by_service.png')

alt.Chart(...)

## 5.6 Cross-Service Distance Matrix

Zooming out: for each pair of services, what is the mean distance between their outputs for the same language? This is the translation-space analog of the rationale-pairwise similarity metric.

In [15]:
# Pair-wise mean distance between services for the same language
from scipy.spatial.distance import cdist as _cdist

# Use actual service names from llm_rows (capitalized: 'Claude', 'Gemini', ...)
# NOT LLM_SERVICES (lowercase), which would cause all svc_to_idx lookups to miss.
SVC = sorted(llm_rows['service'].unique())
n = len(SVC)
dist_matrix = np.zeros((n, n))

for (lang, term_src), g in llm_rows.groupby(['language_code', 'term_source']):
    svc_to_idx = {r['service']: i for i, r in g.iterrows()}
    for i, s1 in enumerate(SVC):
        for j, s2 in enumerate(SVC):
            if s1 in svc_to_idx and s2 in svc_to_idx and i != j:
                v1 = trans_vecs[svc_to_idx[s1]:svc_to_idx[s1]+1]
                v2 = trans_vecs[svc_to_idx[s2]:svc_to_idx[s2]+1]
                dist_matrix[i, j] += _cdist(v1, v2, metric='cosine').item()

# Normalize by count of languages where both services have data
counts = np.zeros((n, n))
for (lang, term_src), g in llm_rows.groupby(['language_code', 'term_source']):
    services_here = set(g['service'].tolist())
    for i, s1 in enumerate(SVC):
        for j, s2 in enumerate(SVC):
            if s1 in services_here and s2 in services_here and i != j:
                counts[i, j] += 1

mean_distances = np.where(counts > 0, dist_matrix / np.where(counts == 0, 1, counts), np.nan)

# Long-format for Altair heatmap
heatmap_rows = []
for i, s1 in enumerate(SVC):
    for j, s2 in enumerate(SVC):
        if i != j:
            heatmap_rows.append({
                'service_a': s1,
                'service_b': s2,
                'mean_distance': mean_distances[i, j],
                'n_languages': int(counts[i, j]),
            })
heatmap_df = pd.DataFrame(heatmap_rows)

cross_service_distance_chart = alt.Chart(heatmap_df).mark_rect().encode(
    x=alt.X('service_a:N', title=None),
    y=alt.Y('service_b:N', title=None),
    color=alt.Color('mean_distance:Q', scale=alt.Scale(scheme='reds')),
    tooltip=['service_a:N', 'service_b:N', 'mean_distance:Q', 'n_languages:Q'],
).properties(
    width=300, height=300,
    title='Pairwise cosine distance between service translations',
)
display(cross_service_distance_chart)
save_chart(cross_service_distance_chart, FIGURE_DIR / 'cross_service_translation_distance_matrix.png')

alt.Chart(...)

In [16]:
heatmap_df

,service_a,service_b,mean_distance,n_languages
0,Claude,DeepSeek,0.263356,870
1,Claude,Gemini,0.270370,860
2,Claude,Gemma,0.385909,826
3,Claude,Llama,0.421892,848
4,Claude,Mistral,0.409881,856
5,Claude,OpenAI,0.246719,864
6,Claude,Qwen,0.423185,836
7,DeepSeek,Claude,0.263356,870
8,DeepSeek,Gemini,0.272594,860
9,DeepSeek,Gemma,0.371513,825


## 5.7 Language Family Cluster Analysis

Do languages from the same family cluster together in translation embedding space?
If they do, it means the translation strategies (script, borrowing patterns, morphology)
are consistent within families — which validates the family as an analytical unit for
the paper. If they don't, family membership is a weak predictor of how models translate.

Four views:
1. **Per-language UMAP** — one point per language (mean of its LLM outputs), colored by family
2. **Family centroid distances** — pairwise heatmap of how far each family's centroid is from others
3. **Within-family spread** — how tightly each family clusters internally
4. **HDBSCAN cluster purity** — do unsupervised clusters align with linguistic family labels?

In [17]:
# Per-language mean embedding: average all LLM translations for that language
lang_codes_list, lang_vecs_list, lang_meta_list = [], [], []
for lang, g in llm_rows.groupby('language_code'):
    lang_codes_list.append(lang)
    lang_vecs_list.append(trans_vecs[g.index].mean(axis=0))
    lang_meta_list.append({
        'language_name': g['language_name'].iloc[0],
        'language_family': g['language_family'].iloc[0],
        'has_wikipedia': g['has_wikipedia'].iloc[0],
    })

lang_vecs = np.vstack(lang_vecs_list)  # (n_langs, 384)

# Separate UMAP for per-language view (880 points vs ~3520 → tighter neighborhoods)
lang_reducer = umap.UMAP(n_neighbors=10, min_dist=0.05, metric='cosine', random_state=42)
lang_coords = lang_reducer.fit_transform(lang_vecs)

lang_umap_df = pd.DataFrame({
    'language_code': lang_codes_list,
    'language_name': [m['language_name'] for m in lang_meta_list],
    'language_family': [m['language_family'] for m in lang_meta_list],
    'has_wikipedia': [m['has_wikipedia'] for m in lang_meta_list],
    'umap_x': lang_coords[:, 0],
    'umap_y': lang_coords[:, 1],
})

# Top-8 families for a readable legend; collapse the rest to 'Other'
top_families = lang_umap_df['language_family'].value_counts().head(8).index.tolist()
lang_umap_df['family_plot'] = lang_umap_df['language_family'].where(
    lang_umap_df['language_family'].isin(top_families), 'Other'
)
print(f'Per-language embeddings: {lang_vecs.shape}')
print(f'Top 8 families: {top_families}')

Per-language embeddings: (881, 384)
Top 8 families: ['Indo-European languages', 'Atlantic-Congo', 'Austronesian languages', 'Afro-Asiatic languages', 'Sino-Tibetan languages', 'Uralic languages', 'Turkic', 'Algic']


In [18]:
ax67 = dict(
    x=alt.X('umap_x:Q', title='UMAP-1', axis=alt.Axis(labels=False, ticks=False)),
    y=alt.Y('umap_y:Q', title='UMAP-2', axis=alt.Axis(labels=False, ticks=False)),
)
alt.Chart(lang_umap_df).mark_circle(size=45, opacity=0.7).encode(
    **ax67,
    color=alt.Color('family_plot:N', title='Language Family',
                    scale=alt.Scale(scheme='tableau10')),
    tooltip=['language_name:N', 'language_family:N', 'has_wikipedia:N'],
).properties(
    width=620, height=520,
    title='Per-language translation space — 1 point per language (mean of LLM outputs), colored by family',
)

alt.Chart(...)

In [19]:
from scipy.spatial.distance import squareform

# Families with ≥5 languages; compute centroids and pairwise distances
fam_counts = lang_umap_df['language_family'].value_counts()
valid_fams = fam_counts[fam_counts >= 5].index.tolist()
fam_order = sorted(valid_fams, key=lambda f: -fam_counts[f])

fam_centroids, fam_idx_map = {}, {}
for fam in valid_fams:
    idxs = [i for i, m in enumerate(lang_meta_list) if m['language_family'] == fam]
    fam_idx_map[fam] = idxs
    fam_centroids[fam] = lang_vecs[idxs].mean(axis=0)

centroid_mat = np.vstack([fam_centroids[f] for f in fam_order])
row_norms = np.linalg.norm(centroid_mat, axis=1, keepdims=True)
centroid_mat_normed = centroid_mat / np.where(row_norms == 0, 1.0, row_norms)
centroid_dists = squareform(pdist(centroid_mat_normed, metric='cosine'))

heat_rows = [
    {'family_a': fam_order[i], 'family_b': fam_order[j], 'distance': centroid_dists[i, j]}
    for i in range(len(fam_order)) for j in range(len(fam_order))
]
heat_df = pd.DataFrame(heat_rows)

alt.Chart(heat_df[heat_df['family_a'] != heat_df['family_b']]).mark_rect().encode(
    x=alt.X('family_a:N', sort=fam_order, title=None, axis=alt.Axis(labelAngle=-45)),
    y=alt.Y('family_b:N', sort=fam_order, title=None),
    color=alt.Color('distance:Q', scale=alt.Scale(scheme='blues', reverse=True),
                    title='Cosine distance'),
    tooltip=['family_a:N', 'family_b:N', alt.Tooltip('distance:Q', format='.3f')],
).properties(
    width=440, height=440,
    title='Family centroid distances — darker = more similar translation strategies',
)

alt.Chart(...)

In [20]:
# Within-family spread: mean cosine distance of each language from its family centroid
spread_rows = []
for fam in valid_fams:
    idxs = fam_idx_map[fam]
    centroid = fam_centroids[fam]
    centroid_norm = centroid / (np.linalg.norm(centroid) or 1.0)
    vecs_sub = lang_vecs[idxs]
    row_norms = np.linalg.norm(vecs_sub, axis=1, keepdims=True)
    vecs_norm = vecs_sub / np.where(row_norms == 0, 1.0, row_norms)
    dists = 1 - (vecs_norm @ centroid_norm)
    spread_rows.append({
        'language_family': fam,
        'mean_spread': float(dists.mean()),
        'n_languages': len(idxs),
    })

spread_df = pd.DataFrame(spread_rows).sort_values('mean_spread')

alt.Chart(spread_df).mark_bar().encode(
    y=alt.Y('language_family:N', sort=alt.SortField('mean_spread', order='ascending'), title=None),
    x=alt.X('mean_spread:Q', title='Mean cosine distance from family centroid'),
    color=alt.Color('n_languages:Q', scale=alt.Scale(scheme='greens'), title='N languages'),
    tooltip=['language_family:N', alt.Tooltip('mean_spread:Q', format='.3f'), 'n_languages:Q'],
).properties(
    width=480, height=max(200, len(spread_df) * 22),
    title='Within-family spread — lower = languages cluster more tightly within family',
)

alt.Chart(...)

In [21]:
# HDBSCAN cluster purity: how well do unsupervised clusters align with language families?
clusterer = hdbscan.HDBSCAN(min_cluster_size=8, metric='euclidean', cluster_selection_method='eom')
cluster_labels = clusterer.fit_predict(lang_vecs)
lang_umap_df['hdbscan_cluster'] = cluster_labels

n_found = int(cluster_labels.max()) + 1
noise_pct = (cluster_labels == -1).mean() * 100
print(f'HDBSCAN: {n_found} clusters, {noise_pct:.1f}% of languages assigned as noise')

purity_rows = []
for cl in range(n_found):
    sub = lang_umap_df[lang_umap_df['hdbscan_cluster'] == cl]
    top_family = sub['language_family'].value_counts().idxmax()
    purity = sub['language_family'].value_counts().iloc[0] / len(sub)
    purity_rows.append({'cluster': cl, 'dominant_family': top_family, 'purity': purity, 'n_languages': len(sub)})

purity_df = pd.DataFrame(purity_rows).sort_values('purity', ascending=False)
print(f'Mean cluster purity (% same family): {purity_df["purity"].mean():.3f}')
print(purity_df.to_string(index=False))
purity_df['cluster_label'] = 'Cluster ' + purity_df['cluster'].astype(str)
cluster_purity_chart = alt.Chart(purity_df).mark_bar().encode(
    x=alt.X('purity:Q', scale=alt.Scale(domain=[0, 1]), title='Dominant-family share'),
    y=alt.Y('cluster_label:N', sort='-x', title=None),
    color=alt.Color('dominant_family:N', title='Dominant family'),
    tooltip=['cluster_label:N', 'dominant_family:N', alt.Tooltip('purity:Q', format='.2f'), 'n_languages:Q'],
).properties(width=480, height=220, title='Family purity of the five HDBSCAN translation clusters')
display(cluster_purity_chart)
save_chart(cluster_purity_chart, FIGURE_DIR / 'translation_cluster_family_purity.png')

HDBSCAN: 5 clusters, 90.5% of languages assigned as noise
Mean cluster purity (% same family): 0.741
 cluster         dominant_family   purity  n_languages
       4  Afro-Asiatic languages 1.000000            8
       2  Austronesian languages 0.888889           18
       3 Indo-European languages 0.800000           35
       1          Atlantic-Congo 0.571429           14
       0        Uralic languages 0.444444            9


alt.Chart(...)

## 5.8 Exact-Convergence Language Clusters

**Primary purpose: compare string convergence with embedding geometry.** If exact-convergence languages function as identifiable reference points, nearby translations may share semantic or orthographic structure. If they do not, exact convergence remains a string-level property rather than a distinct embedding region.

English is present in the dataset as a target language but falls outside exact convergence because Ollama translates "Digital Humanities" into French: a single-service aberration. We force `'en'` into the hub pool using its actual mean embedding (all four LLM outputs averaged), so Ollama's quirk is diluted rather than used to exclude English as a reference point.

For every non-consensus language, we find its nearest hub in embedding space and report the assignment. **The geometry is real; the interpretation requires care.**

---

**Reading the results honestly.** The Portuguese hub attracts roughly 400 languages; the largest cluster by far. This result is not evidence of Portuguese linguistic influence specifically. It reflects the prevalence of Latin-script two-word compounds in the dataset: Portuguese's *Humanidades Digitais* sits near many other Latin-script two-word translations in the embedding model's surface representation, making it the nearest hub for a large structural mass of languages. The finding is geometric, not cultural.

The more interpretable clusters are the smaller ones. Some hub assignments correspond to known historical or contact relationships:
- **Spanish** attracts several Philippine languages (Bikol, Cebuano, Ladino/Judeo-Spanish) plausibly reflecting colonial-era contact
- **French** attracts Vietnamese, Malay, and Negeri Sembilan Malay, consistent with Francophone Southeast Asian linguistic history
- **English** attracts a heterogeneous mix of high-resource European and isolated-script languages, consistent with English functioning as the dominant DH prestige language globally

Others are orthographic coincidence: Plautdietsch and Gheg Albanian clustering near Portuguese reflects Latin-script surface similarity, not meaningful influence.

**The distinction matters.** Some hub assignments correspond to known historical or contact relationships; others reflect orthographic similarity that is not interpretable as influence. Both are real geometric findings, but only the first kind tells you something about translation strategy. The second kind is a reminder that the embedding space is organized by surface features, which can be meaningful (script, borrowing patterns) but can also be misleading (orthographic coincidence). The Portuguese hub's large size is a geometric fact, but it doesn't mean Portuguese is the dominant influence on all those languages' translations.

---

Three views:
1. **Nearest-hub UMAP** — every language colored by which consensus hub it sits closest to
2. **Network** — lines from each language to its nearest hub (top-15 per hub to stay readable)
3. **Cluster sizes** — how many languages each hub attracts, broken down by language family

In [22]:
from scipy.spatial.distance import cdist as cdist_colonial

analysis_df = read_csv_file(os.path.join(EVAL_DIR, 'disagreement_analysis.csv'))

consensus_codes = set(
    analysis_df[analysis_df['comparison_status'] == 'exact_convergence']['language_code']
)
print(f'Exact-convergence hubs: {len(consensus_codes)}')

# ── Force English into the hub pool ──────────────────────────────────────────
# English IS in the translation data but Ollama translates it into French, preventing exact convergence.  We override the classifier verdict and treat English as a hub using its actual mean embedding (all four LLM outputs averaged).
consensus_codes_ext = consensus_codes | {'en'}
print(f'Total hubs (incl. English): {len(consensus_codes_ext)}')

# English already has a row in lang_umap_df — no extension needed
colonial_lang_umap_df = lang_umap_df

cons_idx    = [i for i, c in enumerate(lang_codes_list) if c in consensus_codes_ext]
noncons_idx = [i for i, c in enumerate(lang_codes_list) if c not in consensus_codes_ext]

dist_nc_c = cdist_colonial(lang_vecs[noncons_idx], lang_vecs[cons_idx], metric='cosine')
nearest   = dist_nc_c.argmin(axis=1)

colonial_rows = []
for i, nc_global in enumerate(noncons_idx):
    c_global = cons_idx[nearest[i]]
    colonial_rows.append({
        'language_code':   lang_codes_list[nc_global],
        'language_name':   lang_meta_list[nc_global]['language_name'],
        'language_family': lang_meta_list[nc_global]['language_family'],
        'hub_code':        lang_codes_list[c_global],
        'hub_name':        lang_meta_list[c_global]['language_name'],
        'distance_to_hub': float(dist_nc_c[i, nearest[i]]),
        'is_hub': False,
    })
for c_global in cons_idx:
    colonial_rows.append({
        'language_code':   lang_codes_list[c_global],
        'language_name':   lang_meta_list[c_global]['language_name'],
        'language_family': lang_meta_list[c_global]['language_family'],
        'hub_code':        lang_codes_list[c_global],
        'hub_name':        lang_meta_list[c_global]['language_name'],
        'distance_to_hub': 0.0,
        'is_hub': True,
    })

colonial_df = pd.DataFrame(colonial_rows)
print(f'\nDistance to nearest consensus hub:')
print(colonial_df[~colonial_df['is_hub']]['distance_to_hub'].describe().round(3))
print(f'\nHub names: {sorted(colonial_df["hub_name"].unique())}')

Exact-convergence hubs: 5
Total hubs (incl. English): 6

Distance to nearest consensus hub:
count    875.000
mean       0.233
std        0.180
min        0.010
25%        0.075
50%        0.180
75%        0.365
max        0.697
Name: distance_to_hub, dtype: float64

Hub names: ['Catalan; Valencian', 'English', 'French', 'Korean', 'Portuguese', 'Spanish; Castilian']


In [23]:
# Network: draw lines from each language to its nearest consensus hub Limit to top-15 closest languages per hub to keep the visual readable
TOP_N_NETWORK = 15
edges = (
    colonial_df[~colonial_df['is_hub']]
    .sort_values('distance_to_hub')
    .groupby('hub_code')
    .head(TOP_N_NETWORK)
    .copy()
)

# Merge non-hub UMAP coords (the line's start point)
edges = edges.merge(
    colonial_lang_umap_df[['language_code', 'umap_x', 'umap_y']],
    on='language_code',
    how='left',
)

# Merge hub UMAP coords onto edge rows (the line's end point)
hub_coords = colonial_lang_umap_df.set_index('language_code')[['umap_x', 'umap_y']].rename(
    columns={'umap_x': 'hub_x', 'umap_y': 'hub_y'}
)
edges = edges.join(hub_coords, on='hub_code')

hub_pts = colonial_df[colonial_df['is_hub']].merge(
    colonial_lang_umap_df[['language_code', 'umap_x', 'umap_y']], on='language_code'
)
non_hub_pts = colonial_df[~colonial_df['is_hub']].merge(
    colonial_lang_umap_df[['language_code', 'umap_x', 'umap_y']], on='language_code'
)

ax_net = dict(
    x=alt.X('umap_x:Q', title='UMAP-1', axis=alt.Axis(labels=False, ticks=False)),
    y=alt.Y('umap_y:Q', title='UMAP-2', axis=alt.Axis(labels=False, ticks=False)),
)
edge_layer = alt.Chart(edges).mark_rule(opacity=0.18, strokeWidth=0.8).encode(
    x=alt.X('umap_x:Q'), y=alt.Y('umap_y:Q'),
    x2='hub_x:Q', y2='hub_y:Q',
    color=alt.Color('hub_name:N', scale=alt.Scale(scheme='tableau20'), legend=None),
)
non_hub_layer = alt.Chart(non_hub_pts).mark_circle(size=18, opacity=0.5).encode(
    **ax_net,
    color=alt.Color('hub_name:N', scale=alt.Scale(scheme='tableau20'), title='Nearest hub'),
    tooltip=['language_name:N', 'language_family:N', 'hub_name:N',
             alt.Tooltip('distance_to_hub:Q', format='.3f', title='Distance to hub')],
)
hub_layer = alt.Chart(hub_pts).mark_point(size=180, shape='diamond', filled=True,
                                           opacity=1.0, strokeWidth=1.5,
                                           stroke='black').encode(
    **ax_net,
    color=alt.Color('hub_name:N', scale=alt.Scale(scheme='tableau20'), legend=None),
    tooltip=['language_name:N', 'hub_name:N'],
)
hub_labels = alt.Chart(hub_pts).mark_text(dy=-12, fontSize=9, fontWeight='bold').encode(
    **ax_net,
    text='language_name:N',
    color=alt.Color('hub_name:N', scale=alt.Scale(scheme='tableau20'), legend=None),
)
(edge_layer + non_hub_layer + hub_layer + hub_labels).properties(
    width=640, height=540,
    title=alt.TitleParams(
        'Consensus translation network — languages connected to nearest consensus hub',
        subtitle=f'Diamonds = consensus hubs (incl. English, forced). Lines show {TOP_N_NETWORK} closest languages per hub.',
        subtitleColor='#666', subtitleFontSize=11,
    ),
).interactive()

alt.LayerChart(...)

In [24]:
# Bar chart: how many languages each consensus hub attracts, broken down by family
hub_sizes = (
    colonial_df[~colonial_df['is_hub']]
    .groupby(['hub_name', 'language_family'])
    .size()
    .reset_index(name='n')
)
hub_totals = hub_sizes.groupby('hub_name')['n'].sum().sort_values(ascending=False)
hub_order = hub_totals.index.tolist()
hub_totals_df = hub_totals.rename('n').reset_index()

# Top-15 languages per hub as text summary
print('Languages per consensus hub (total attracted):')
for hub in hub_order:
    n = int(hub_totals[hub])
    closest = (
        colonial_df[~colonial_df['is_hub'] & (colonial_df['hub_name'] == hub)]
        .nsmallest(5, 'distance_to_hub')['language_name']
        .tolist()
    )
    print(f'  {hub:<28} {n:>3} languages  |  closest: {", ".join(closest[:3])}')

hub_bars = alt.Chart(hub_totals_df).mark_bar(color='#4c78a8').encode(
    y=alt.Y('hub_name:N', sort=hub_order, title='Consensus hub language'),
    x=alt.X('n:Q', title='Languages attracted'),
    tooltip=['hub_name:N', 'n:Q'],
).properties(
    width=540, height=max(200, len(hub_order) * 30),
    title='Languages assigned to each nearest consensus hub',
)
hub_labels = hub_bars.mark_text(align='left', dx=4, color='black').encode(text='n:Q')
consensus_hub_sizes_chart = hub_bars + hub_labels
display(consensus_hub_sizes_chart)
save_chart(consensus_hub_sizes_chart, FIGURE_DIR / 'consensus_hub_cluster_sizes.png')

Languages per consensus hub (total attracted):
  Portuguese                   470 languages  |  closest: Parthian, Tetum, Sranan Tongo
  English                      111 languages  |  closest: Sora, Garo, Scots
  Catalan; Valencian           100 languages  |  closest: Romanian, Moldavan, Negeri Sembilan Malay, Pattani Malay
  French                        93 languages  |  closest: Middle French, Malay, Old French
  Spanish; Castilian            93 languages  |  closest: Kabuverdianu, Bikol, Cebuano
  Korean                         8 languages  |  closest: Min Nan Chinese, Hakka Chinese, Central Okinawan


alt.LayerChart(...)

## 5.9 Expected vs. Actual Family Clustering Network

§6.7 asked whether language families cluster together in translation embedding space. This section makes that question concrete by building **two graphs** and comparing them directly:

- **Expected graph** (edge = same linguistic family): which language pairs *should* cluster together based on their family membership?
- **Actual graph** (edge = top-5 nearest translation neighbors): which language pairs *do* cluster together based on their mean LLM translation embeddings?

Overlaying these reveals:
- **True positives** — same-family pairs that also cluster (translation captures family similarity)
- **False positives** — cross-family pairs that cluster (translation similarity crosses family lines — often colonial borrowing or shared loanword strategies)
- **False negatives** — same-family pairs that don't cluster (translation diverges within a family)

The network is drawn in UMAP coordinates (same projection as §6.7), colored by language family, with solid edges for actual neighbors and dashed edges for expected-but-absent same-family connections.

In [25]:
from scipy.spatial.distance import cdist as cdist69

TOP_K_NEIGHBORS = 5  # adjustable: top-k nearest actual neighbors per language

# ── Build actual-neighbor graph ──────────────────────────────────────────────
# Use cosine similarity on raw embeddings (more reliable than UMAP coords for distance)
norms = np.linalg.norm(lang_vecs, axis=1, keepdims=True)
normed = lang_vecs / np.where(norms == 0, 1.0, norms)
cos_sim = normed @ normed.T  # (n, n) cosine similarity matrix

actual_edges = []
for i, lc_i in enumerate(lang_codes_list):
    sims = cos_sim[i].copy()
    sims[i] = -1  # exclude self
    top_idxs = sims.argsort()[-TOP_K_NEIGHBORS:][::-1]
    for j in top_idxs:
        lc_j = lang_codes_list[j]
        actual_edges.append({
            'src': lc_i,
            'dst': lc_j,
            'similarity': float(sims[j]),
        })

actual_edge_set = {(r['src'], r['dst']) for r in actual_edges}

# ── Build expected graph (same linguistic family) ───────────────────────────
lc_to_fam = {m['language_code']: m['language_family']
               for m in [{**{'language_code': lc}, **meta}
                         for lc, meta in zip(lang_codes_list, lang_meta_list)]}
# Use lang_umap_df which already has family
lc_fam_map = dict(zip(lang_umap_df['language_code'], lang_umap_df['language_family']))

expected_edges = []
for i, lc_i in enumerate(lang_codes_list):
    fam_i = lc_fam_map.get(lc_i, '')
    for j, lc_j in enumerate(lang_codes_list):
        if i >= j:
            continue
        fam_j = lc_fam_map.get(lc_j, '')
        if fam_i and fam_j and fam_i == fam_j and fam_i != 'Other':
            expected_edges.append({'src': lc_i, 'dst': lc_j, 'family': fam_i})

expected_edge_set = {(r['src'], r['dst']) for r in expected_edges} |                     {(r['dst'], r['src']) for r in expected_edges}

# ── Precision / Recall ───────────────────────────────────────────────────────
actual_set_both = actual_edge_set | {(b, a) for a, b in actual_edge_set}

tp = sum(1 for e in actual_edges if (e['src'], e['dst']) in expected_edge_set)
fp = sum(1 for e in actual_edges if (e['src'], e['dst']) not in expected_edge_set)
fn_count = sum(1 for e in expected_edges
               if (e['src'], e['dst']) not in actual_set_both
               and (e['dst'], e['src']) not in actual_set_both)

precision = tp / len(actual_edges) if actual_edges else 0
recall    = tp / len(expected_edges) if expected_edges else 0

print(f"Actual graph   : {len(actual_edges)} directed edges  (top-{TOP_K_NEIGHBORS} per language)")
print(f"Expected graph : {len(expected_edges)} undirected same-family edges")
print(f"True positives : {tp}  (actual edges that are also same-family)")
print(f"False positives: {fp}  (actual edges crossing family lines)")
print(f"False negatives: {fn_count}  (same-family pairs that don't appear in actual top-{TOP_K_NEIGHBORS})")
print(f"Precision      : {precision:.3f}")
print(f"Recall         : {recall:.3f}")
print(f"F1             : {2*precision*recall/(precision+recall):.3f}" if (precision+recall) > 0 else "F1: 0")

Actual graph   : 4405 directed edges  (top-5 per language)
Expected graph : 47436 undirected same-family edges
True positives : 2196  (actual edges that are also same-family)
False positives: 2209  (actual edges crossing family lines)
False negatives: 45860  (same-family pairs that don't appear in actual top-5)
Precision      : 0.499
Recall         : 0.046
F1             : 0.085


In [26]:
import altair as alt

# ── Prepare node and edge data for Altair ───────────────────────────────────
# Nodes: from lang_umap_df (already in UMAP space)
top_fams_69 = (
    lang_umap_df['language_family'].value_counts()
    .head(9).index.tolist()
)
nodes = lang_umap_df.copy()
nodes['family_plot'] = nodes['language_family'].apply(
    lambda f: f if f in top_fams_69 else 'Other'
)

# Actual edges: pick a reasonable visual subset
# Keep only edges where at least one endpoint is in a named family (avoids hairball)
named_lcs = set(nodes[nodes['family_plot'] != 'Other']['language_code'])
actual_viz = [e for e in actual_edges
               if e['src'] in named_lcs or e['dst'] in named_lcs]

# Merge UMAP coords onto edges
umap_idx = nodes.set_index('language_code')[['umap_x', 'umap_y', 'family_plot']]
edge_rows = []
for e in actual_viz:
    if e['src'] not in umap_idx.index or e['dst'] not in umap_idx.index:
        continue
    sx, sy = umap_idx.loc[e['src'], ['umap_x', 'umap_y']]
    dx, dy = umap_idx.loc[e['dst'], ['umap_x', 'umap_y']]
    same_family = (e['src'], e['dst']) in expected_edge_set or (e['dst'], e['src']) in expected_edge_set
    edge_rows.append({
        'x': sx, 'y': sy, 'x2': dx, 'y2': dy,
        'similarity': e['similarity'],
        'edge_type': 'same-family' if same_family else 'cross-family',
    })
edge_df = pd.DataFrame(edge_rows)

# ── Altair network chart ─────────────────────────────────────────────────────
_ax = dict(
    axis=alt.Axis(labels=False, ticks=False, grid=False),
)

# Edge layer (rule = straight lines between x,y and x2,y2)
edge_layer = alt.Chart(edge_df).mark_rule(opacity=0.3, strokeWidth=0.8).encode(
    x=alt.X('x:Q', title='UMAP-1', **_ax),
    y=alt.Y('y:Q', title='UMAP-2', **_ax),
    x2='x2:Q',
    y2='y2:Q',
    color=alt.Color('edge_type:N',
                    scale=alt.Scale(
                        domain=['same-family', 'cross-family'],
                        range=['#2ca02c', '#d62728']
                    ),
                    title='Edge type'),
    strokeDash=alt.condition(
        alt.datum.edge_type == 'cross-family',
        alt.value([4, 2]),
        alt.value([1, 0]),
    ),
    tooltip=['edge_type:N', alt.Tooltip('similarity:Q', format='.3f')],
)

# Node layer
node_layer = alt.Chart(nodes).mark_circle(size=40, opacity=0.8).encode(
    x=alt.X('umap_x:Q', title='UMAP-1', **_ax),
    y=alt.Y('umap_y:Q', title='UMAP-2', **_ax),
    color=alt.Color('family_plot:N', title='Language Family',
                    scale=alt.Scale(scheme='tableau10')),
    tooltip=['language_name:N', 'language_family:N'],
)

network_chart = (edge_layer + node_layer).properties(
    width=700, height=580,
    title=f'Expected vs. Actual Family Clustering — top-{TOP_K_NEIGHBORS} neighbors per language'
).resolve_scale(color='independent')

display(network_chart)
save_chart(network_chart, FIGURE_DIR / 'expected_vs_actual_family_clustering_network.png')

alt.LayerChart(...)

In [27]:
# ── Cross-family borrowing analysis ─────────────────────────────────────────
# Which family pairs most often appear as cross-family actual neighbors?
cross_rows = []
for e in actual_edges:
    fam_src = lc_fam_map.get(e['src'], 'Other')
    fam_dst = lc_fam_map.get(e['dst'], 'Other')
    if fam_src != fam_dst and fam_src != 'Other' and fam_dst != 'Other':
        pair = tuple(sorted([fam_src, fam_dst]))
        cross_rows.append({'family_pair': f'{pair[0]} ↔ {pair[1]}',
                           'similarity': e['similarity']})

cross_df = (
    pd.DataFrame(cross_rows)
    .groupby('family_pair')
    .agg(n_edges=('similarity','count'), mean_sim=('similarity','mean'))
    .reset_index()
    .sort_values('n_edges', ascending=False)
)
print("Top cross-family neighbor pairs (translation similarity crossing family lines):")
print(cross_df.head(15).to_string(index=False))

# Families with best within-family recall (most same-family pairs in top-K)
recall_rows = []
for fam in top_fams_69:
    fam_lcs = set(nodes[nodes['family_plot'] == fam]['language_code'])
    n_expected = len(fam_lcs) * (len(fam_lcs) - 1)  # directed pairs
    n_actual_tp = sum(
        1 for e in actual_edges
        if e['src'] in fam_lcs and e['dst'] in fam_lcs
    )
    if n_expected > 0:
        recall_rows.append({'family': fam, 'n_languages': len(fam_lcs),
                            'n_expected_pairs': n_expected,
                            'n_actual_tp': n_actual_tp,
                            'recall': n_actual_tp / n_expected})

recall_fam_df = (pd.DataFrame(recall_rows)
                 .sort_values('recall', ascending=False))
print("\nWithin-family recall by family (fraction of same-family pairs that are top-K neighbors):")
print(recall_fam_df.to_string(index=False))

Top cross-family neighbor pairs (translation similarity crossing family lines):
                                     family_pair  n_edges  mean_sim
Indo-European languages ↔ Sino-Tibetan languages      144  0.971334
Austronesian languages ↔ Indo-European languages       87  0.963199
Afro-Asiatic languages ↔ Indo-European languages       82  0.931973
                          Atlantic-Congo ↔ Mande       70  0.949875
   Dravidian languages ↔ Indo-European languages       58  0.948607
                Indo-European languages ↔ Turkic       55  0.933148
         Atlantic-Congo ↔ Austronesian languages       54  0.929596
   Creoles and pidgins ↔ Indo-European languages       53  0.951140
      Indo-European languages ↔ Uralic languages       51  0.954583
                        Atlantic-Congo ↔ Nilotic       47  0.923564
  Artificial languages ↔ Indo-European languages       44  0.946617
        Atlantic-Congo ↔ Indo-European languages       42  0.945849
    Atlantic-Congo ↔ Niger-Kordofani